In [0]:
# Nomes do catalog e das camadas
catalog = "cinedata"

bronze_schema = f"{catalog}.bronze"
silver_schema = f"{catalog}.silver"
gold_schema = f"{catalog}.gold"

landing_path = f"/Volumes/{catalog}/bronze/landing"

In [0]:
from pyspark.sql import functions as F
# Dimensão de filmes
df_movies_silver = spark.table(f"{silver_schema}.tb_info_filmes")

df_dim_movies = (
    df_movies_silver
    .withColumn("id_filme", F.col("id_filme").cast("string"))
    .select(
        # Cria a coluna de id
        F.monotonically_increasing_id().alias("sk_movie_id"),
        "id_filme", "titulo", "data_lancamento", "ano_lancamento",
        "duracao_minutos", "idioma_original", "status_filme", "sinopse")
)

display(df_dim_movies)
df_dim_movies.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.dim_movies")

sk_movie_id,id_filme,titulo,data_lancamento,ano_lancamento,duracao_minutos,idioma_original,status_filme,sinopse
0,233863,Jimi Hendrix: Hear My Train A Comin',2020-09-11,2020,90,en,Lançado,"An account of the short life of genius musician Jimi Hendrix (1942-70), probably the most talented and influential guitarist of the twentieth century: his humble beginnings in Seattle, his time in New York, his rise to fame in swinging London… Live fast, love hard, die young."
1,270711,"Princess, A True Story",2018-09-28,2018,0,es,Lançado,"Two old women who live in a mansion, which is locked between two skyscrapers, hate their neighbors because they are rebel medicine students who party all day long. One day, one of the old ladies get sick and is saved by one of the students, arousing a weird friendship and an opportunity to discover new experiences and change behavior patterns."
2,308531,Teenage Mutant Ninja Turtles: Out Of The Shadows,2016-06-01,2016,112,en,Lançado,"After supervillain Shredder escapes custody, he joins forces with mad scientist Baxter Stockman and two dimwitted henchmen, Bebop and Rocksteady, to unleash a diabolical plan to take over the world. As the Turtles prepare to take on Shredder and his new crew, they find themselves facing an even greater evil with similar intentions: the notorious Krang."
3,331962,Exposed,2016-01-22,2016,102,en,Lançado,"After witnessing a miracle, a young Latina woman experiences strange things as a police detective searches for the truth behind his partner's death."
4,339988,The Circle,2017-04-27,2017,110,en,Lançado,"A young tech worker takes a job at a powerful Internet corporation, quickly rises up the company's ranks, and soon finds herself in a perilous situation concerning privacy, surveillance and freedom. She comes to learn that her decisions and actions will determine the future of humanity."
5,345937,Unleashed,2017-08-25,2017,96,en,Lançado,"When a cosmic event turns Emma's dog and cat into two perfect guys, Emma reconsiders her outlook on dating, hilariously works out her trust issues, and ultimately learns to love herself."
6,354273,Love Addict,2016-05-13,2016,89,en,Lançado,"A womanizing attorney is unable to have sex after a hypnotherapy session to quit smoking goes awry and he seeks help from one of his clients, an uptight psychiatrist, who teaches him that there is more to women than just sex."
7,359412,Marauders,2016-07-01,2016,107,en,Lançado,An untraceable group of elite bank robbers is chased by a suicidal FBI agent who uncovers a deeper purpose behind the robbery-homicides.
8,370105,Escapades With Friends,2016-02-27,2016,88,de,Lançado,Once during a party two friends get an idea: let's exchange wives...
9,375107,Duck Duck Goose,2018-03-09,2018,82,en,Lançado,null


In [0]:
df_genres_silver = spark.table(f"{silver_schema}.tb_generos")

df_dim_genres = (
    df_genres_silver
    # Mantém uma linha por gênero
    .dropDuplicates(["genero"])
    .select(
        # Cria o id
        F.monotonically_increasing_id().alias("sk_genre_id"),
        F.col("genero").alias("nome_genero")
    )
)

display(df_dim_genres)
df_dim_genres.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.dim_genres")

sk_genre_id,nome_genero
0,Mystery
1,Animation
2,Science Fiction
3,Action
4,Family
5,Romance
6,History
7,Comedy
8,Crime
9,Thriller


In [0]:
df_pessoas_empresas_silver = spark.table(f"{silver_schema}.tb_pessoas_empresas")

df_dim_people = (
    df_pessoas_empresas_silver
    # Mantém somente os registros que são pessoas
    .filter(F.col("tipo_entidade").isin(["Ator", "Diretor", "Roteirista"]))
    # Tira duplicações de pessoa+função
    .dropDuplicates(["nome_entidade", "tipo_entidade"])
    .select(
        # Cria o id
        F.monotonically_increasing_id().alias("sk_person_id"),
        F.col("nome_entidade").alias("nome_pessoa"),
        F.col("tipo_entidade").alias("tipo_pessoa")
    )
)

display(df_dim_people)
df_dim_people.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.dim_people")

sk_person_id,nome_pessoa,tipo_pessoa
0,Don Cheadle,Ator
1,Hugh Jackman,Ator
2,Anthony Gonzalez,Ator
3,Daniel Kaluuya,Ator
4,Mike Myers,Ator
5,Mark Rylance,Ator
6,Ewan Mcgregor,Ator
7,Tom Hardy,Ator
8,Evangeline Lilly,Ator
9,Randall Park,Ator


In [0]:
df_dim_companies = (
    df_pessoas_empresas_silver
    # Mantém somente a Produtora
    .filter(F.col("tipo_entidade") == "Produtora")
    # Tira os duplicados
    .dropDuplicates(["nome_entidade"])
    .select(
        # Cria o id
        F.monotonically_increasing_id().alias("sk_company_id"),
        F.col("nome_entidade").alias("nome_produtora")
    )
)

display(df_dim_companies)
df_dim_companies.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.dim_companies")

sk_company_id,nome_produtora
0,Gk Films
1,Regency Enterprises
2,Matt Tolmach Productions
3,Walt Disney Pictures
4,Gunn Films
5,Offspring Entertainment
6,Evergreen Media Group
7,Seven Bucks Productions
8,Huayi Brothers Pictures
9,Ratpac Entertainment


In [0]:
df_avaliacoes_silver = spark.table(f"{silver_schema}.tb_avaliacoes_usuarios")

df_dim_filmes = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "id_filme")

df_dim_reviews = (
    # Faz o join da tabela silver de avaliações com a dimensão de filmes para pegar o novo id dos filmes
    df_dim_filmes
    .join(df_avaliacoes_silver, on="id_filme", how="left")
    .groupBy("sk_movie_id")
    .agg(
        # Conta as avalizações para cada filme
        F.count("nota_usuario").alias("qtd_avaliacoes_usuarios"),
        # Calcula a média da nota, se não há notas, a média é 0
        F.coalesce(F.avg("nota_usuario"), F.lit(0)).alias("nota_media_usuarios")
    )
    .select(
        # Cria o id
        F.monotonically_increasing_id().alias("sk_review_id"),
        "sk_movie_id", "qtd_avaliacoes_usuarios", "nota_media_usuarios"
    )
)

display(df_dim_reviews)
df_dim_reviews.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.dim_reviews")

sk_review_id,sk_movie_id,qtd_avaliacoes_usuarios,nota_media_usuarios
0,28,1,0.1
1,151,2,5.199999999999999
2,171,1,4.0
3,200,1,1.0
4,224,2,5.3
5,248,1,2.5
6,269,1,6.6
7,271,1,2.6
8,401,1,8.4
9,406,1,8.8


In [0]:
# bridge table: filme-gênero
df_dim_filmes = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "id_filme")
df_generos_silver = spark.table(f"{silver_schema}.tb_generos")
df_dim_generos = spark.table(f"{gold_schema}.dim_genres")

df_bridge_movie_genre = (
    # Faz o join das tabelas de dimensão de filme e gênero (para ter os id)
    # com a tabela silver (para ter os relacionamentos de filme com gênero) 
    df_generos_silver
    .join(df_dim_generos, df_generos_silver["genero"] == df_dim_generos["nome_genero"], "inner")
    .join(df_dim_filmes, "id_filme", "inner")
    .select("sk_movie_id", "sk_genre_id")
)

display(df_bridge_movie_genre)
df_bridge_movie_genre.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.bridge_movie_genre")

sk_movie_id,sk_genre_id
36116,303
3774,421
30951,97
48339,217
9741,62
60209,63
10282,217
39202,217
88184,274
89189,217


In [0]:
# bridge table: filme-pessoa
df_dim_filmes = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "id_filme")
df_pessoas_empresas_silver = spark.table(f"{silver_schema}.tb_pessoas_empresas").select("nome_entidade", "id_filme")
df_dim_pessoas = spark.table(f"{gold_schema}.dim_people").select("sk_person_id", "nome_pessoa")

df_bridge_movie_person = (
    # Faz o join das tabelas de dimensão de filme e pessoas (para ter os id)
    # com a tabela silver (para ter o relacionamento de filme com pessoa) 
    df_pessoas_empresas_silver
    .join(df_dim_pessoas, df_pessoas_empresas_silver["nome_entidade"] == df_dim_pessoas["nome_pessoa"], "inner")
    .join(df_dim_filmes, "id_filme", "inner")
    .select("sk_movie_id", "sk_person_id")
)

display(df_bridge_movie_person)
df_bridge_movie_person.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.bridge_movie_person")

sk_movie_id,sk_person_id
53405,289198
69463,236073
38173,105293
20929,313581
47888,105294
26182,315451
34054,157604
16100,157605
33548,105295
33548,392927


In [0]:
from datetime import timedelta

# 5. Qual ator teve a maior quantidade de participações nos filmes lançados nos últimos 2 anos*?
# Seleciona os filmes lançados
df_dim_movies = spark.table(f"{gold_schema}.dim_movies")\
    .filter((F.col("status_filme") == "Lançado") & (F.col("data_lancamento") <= F.current_date()))\
    .select("sk_movie_id", "data_lancamento")
df_atores = spark.table(f"{gold_schema}.dim_people").filter(F.col("tipo_pessoa") == "Ator")
df_bridge_movie_person = spark.table(f"{gold_schema}.bridge_movie_person")

# Para pegar 2 anos antes da data mais recente: retira dois anos da data e pega a maior
data_dois_anos = df_dim_movies.agg(F.max(F.add_months(F.col("data_lancamento"), -24))).first()[0]

ator = (
    df_dim_movies
    # Mantém só os filmes dos últimos 2 anos
    .filter(F.col("data_lancamento") >= data_dois_anos)
    # Join pega quais atores participaram de cada filme
    .join(df_bridge_movie_person, "sk_movie_id", "inner")
    .join(df_atores, "sk_person_id", "inner")
    # Agrupa por ator
    .groupBy(F.col("sk_person_id"), F.col("nome_pessoa"))
    .count()
    .orderBy(F.col("count"), ascending=False)
)

display(ator)

sk_person_id,nome_pessoa,count
131401,Kevin Hart,8
105719,John Travolta,7
184091,Paula Pell,7
78987,Ben Schwartz,7
236507,Alex Dauphin,7
52925,Greg Kriek,7
53009,Olivia Park,7
157973,Brandon H. Morgan,7
315886,Stacy Hall,7
26911,John Cena,7


In [0]:
# bridge table: filme-empresa
df_dim_filmes = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "id_filme")
df_pessoas_empresas_silver = spark.table(f"{silver_schema}.tb_pessoas_empresas").select("nome_entidade", "id_filme")
df_dim_empresas = spark.table(f"{gold_schema}.dim_companies")

df_bridge_movie_company = (
    # Faz o join das tabelas de dimensão de filme e empresa (para ter os id)
    # com a tabela silver (para ter o relacionamento de filme com empresa) 
    df_pessoas_empresas_silver
    .join(df_dim_empresas, df_pessoas_empresas_silver["nome_entidade"] == df_dim_empresas["nome_produtora"], "inner")
    .join(df_dim_filmes, "id_filme", "inner")
    .select("sk_movie_id", "sk_company_id")
)

display(df_bridge_movie_company)
df_bridge_movie_company.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.bridge_movie_company")

sk_movie_id,sk_company_id
55483,18500
67976,23087
22464,20176
82145,7838
13495,7744
2639,28782
18769,5197
77765,22999
72019,83
30319,17570


In [0]:
# Tabela de fatos
df_movies_silver = spark.table(f"{silver_schema}.tb_info_filmes")
df_financeiro_silver = spark.table(f"{silver_schema}.tb_financeiro_filmes")
df_metricas_silver = spark.table(f"{silver_schema}.tb_metricas_engajamento")
df_dim_movies = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "id_filme")

df_fact_table = (
    # Faz o join de todas as tabelas para ter as informações
    df_movies_silver
    .join(df_dim_movies, "id_filme", "inner")
    .join(df_financeiro_silver, "id_filme", "inner")
    .join(df_metricas_silver, "id_filme", "inner")
    .select(
        "sk_movie_id", "orcamento_usd", "receita_usd", "lucro_usd", "orcamento_brl", "receita_brl",
        "lucro_brl", "popularidade", "nota_media_tmdb", "qtd_votos_tmdb", "nota_media_imdb", "qtd_votos_imdb"
    )
)

display(df_fact_table)
df_fact_table.write.format("delta").mode("overwrite").option("overwriteSchema", "true")\
    .saveAsTable(f"{gold_schema}.fact_movies_performance")

sk_movie_id,orcamento_usd,receita_usd,lucro_usd,orcamento_brl,receita_brl,lucro_brl,popularidade,nota_media_tmdb,qtd_votos_tmdb,nota_media_imdb,qtd_votos_imdb
16096,58000000.00,null,null,2.895882E8,null,null,72.735,7.606,28894,8.0,1270339
53405,300000000.00,2052415039.00,1752415039.00,1.49787E9,1.024750304822E10,8.74963304822E9,154.34,8.255,27713,8.4,1406782
13965,356000000.00,2800000000.00,2444000000.00,1.7774724E9,1.398012E10,1.22026476E10,91.756,8.263,23857,8.4,1484150
82686,55000000.00,1074458282.00,1019458282.00,2.746095E8,5.3646627562E9,5.0900532562E9,54.522,8.168,23425,8.3,1723035
65340,250000000.00,null,null,1.248225E9,null,null,70.741,7.4,21541,7.8,947222
89160,200000000.00,1349926083.00,1149926083.00,9.9858E8,6.74004593981E9,5.74146593981E9,43.665,7.39,null,7.3,924922
7042,180000000.00,676343174.00,496343174.00,8.98722E8,3.37691383346E9,2.47819183346E9,70.535,7.427,20935,7.5,895880
16617,175000000.00,880166924.00,705166924.00,8.737575E8,4.39458543484E9,3.52082793484E9,65.88,7.345,20507,7.4,835116
38689,200000000.00,863756051.00,663756051.00,9.9858E8,4.31264758704E9,3.31406758704E9,67.553,7.624,20353,7.6,844767
86201,175000000.00,746846894.00,571846894.00,8.737575E8,3.72893185705E9,2.85517435705E9,35.356,5.909,20097,5.9,null


## Perguntas

In [0]:
# 1. Qual é a receita total (em R$) somada de todos os filmes da base?
df_fact_movies = spark.table(f"{gold_schema}.fact_movies_performance")

# Somente soma todos os valores da coluna de receita em reais
receita_total = df_fact_movies.select(F.sum(F.col("receita_brl")).alias("Receita total (R$)"))

display(receita_total)

Receita total (R$)
8.282060511130571E11


In [0]:
# 2. Quais são os 5 filmes com maior popularidade? Mostre título e valor de popularidade.
df_fact_movies = spark.table(f"{gold_schema}.fact_movies_performance")
df_dim_movies = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "titulo")

top5_popularidade = (
    # Tabela de fatos tem a popularidade, a de dimensão o título
    df_fact_movies
    .join(df_dim_movies, "sk_movie_id", "inner")
    # Ordena pela popularidade e pega os 5 primeiros
    .orderBy("popularidade", ascending=False)
    .limit(5)
    .select("titulo", "popularidade")
)

display(top5_popularidade)

titulo,popularidade
Asylum Of The Devil,2.0093201020121E12
A Postcard From Pyongyang,2.0132017E7
"The Psychopath, Chronicle Of An Unsolved Case",1.9851995E7
Russian Hackers: The Beginning,902010.0
Russian Hackers: The Beginning,902010.0


In [0]:
# 3. Quantos filmes cada gênero possui? Liste do maior para o menor volume.
df_dim_genres = spark.table(f"{gold_schema}.dim_genres")
df_bridge_movie_genre = spark.table(f"{gold_schema}.bridge_movie_genre")

qtd_por_genero = (
    # Tabela de dimensão tem o nome dos gêneros, a bridge a associação dos filmes com gênero
    df_bridge_movie_genre
    .join(df_dim_genres, "sk_genre_id", "inner")
    # Agrupa por gênero e conta a quantidade de filmes por gênero
    .groupBy("sk_genre_id", "nome_genero")
    .agg(F.count("sk_genre_id").alias("Quantidade de filmes"))
    .orderBy("Quantidade de filmes", ascending=False)
    .select("nome_genero", "Quantidade de filmes")
)

display(qtd_por_genero)

nome_genero,Quantidade de filmes
Drama,30565
Documentary,18576
Comedy,17950
Thriller,9502
Horror,8910
Romance,7350
Action,5729
Crime,4529
Animation,4224
TV Movie,4001


In [0]:
# 4. Para os 10 filmes de maior receita, mostre título, receita (em US$ e R$) e a posição de cada um no ranking (RANK()).
from pyspark.sql import Window

# Tabela de fatos tem a receita, a de dimensão o título
df_fact_movies = spark.table(f"{gold_schema}.fact_movies_performance")
df_dim_movies = spark.table(f"{gold_schema}.dim_movies").select("sk_movie_id", "titulo")

top10_receita = (
    df_fact_movies
    # Pega o ranking de cada filme e o top 10
    .withColumn("ranking", F.rank().over(Window.orderBy(F.col("receita_brl").desc())))
    .filter(F.col("ranking") <= 10)
    # Faz o join com a dimensão de filmes para ter o título
    .join(df_dim_movies, "sk_movie_id", "inner")
    .select("ranking", "titulo", "receita_brl", "receita_usd")
    .orderBy(F.col("ranking"))
)

display(top10_receita)

/databricks/python/lib/python3.12/site-packages/pyspark/sql/connect/expressions.py:1155: UserWarning: WARN WindowExpression: No Partition Defined for Window operation! Moving all data to a single partition, this can cause serious performance degradation.
  warnings.warn(


ranking,titulo,receita_brl,receita_usd
1,Avengers: Endgame,1.398012E10,2800000000.00
2,Avatar: The Way Of Water,1.1584777628E10,2320250281.00
3,Avengers: Infinity War,1.024750304822E10,2052415039.00
4,Spider-man: No Way Home,9.59559044051E9,1921847111.00
5,The Lion King,8.30356916965E9,1663075401.00
6,Top Gun: Maverick,7.43309410197E9,1488732821.00
7,Barbie,7.1325824703E9,1428545028.00
8,The Super Mario Bros. Movie,6.76900066563E9,1355725263.00
9,Black Panther,6.74004593981E9,1349926083.00
10,Star Wars: The Last Jedi,6.65403198831E9,1332698830.00


In [0]:
from datetime import timedelta

# 5. Qual ator teve a maior quantidade de participações nos filmes lançados nos últimos 2 anos*?
# Seleciona os filmes lançados
df_dim_movies = spark.table(f"{gold_schema}.dim_movies")\
    .filter((F.col("status_filme") == "Lançado") & (F.col("data_lancamento") <= F.current_date()))\
    .select("sk_movie_id", "data_lancamento", )
df_atores = spark.table(f"{gold_schema}.dim_people").filter(F.col("tipo_pessoa") == "Ator")
df_bridge_movie_person = spark.table(f"{gold_schema}.bridge_movie_person")

# Para pegar 2 anos antes da data mais recente: retira dois anos da data e pega a maior
data_dois_anos = df_dim_movies.agg(F.max(F.add_months(F.col("data_lancamento"), -24))).first()[0]

qtd_por_ator = (
    df_dim_movies
    # Mantém só os filmes dos últimos 2 anos
    .filter(F.col("data_lancamento") >= data_dois_anos)
    # Join pega quais atores participaram de cada filme
    .join(df_bridge_movie_person, "sk_movie_id", "inner")
    .join(df_atores, "sk_person_id", "inner")
    # Agrupa por ator
    .groupBy(F.col("sk_person_id"), F.col("nome_pessoa"))
    .count()
)
# Pega a contagem máxima e o ator com ela
max_count = qtd_por_ator.agg(F.max(F.col("count"))).first()[0]
ator = qtd_por_ator.filter(F.col("count") == max_count).select(
    "nome_pessoa", F.col("count").alias("Quantidade de filmes")
)

display(ator)

nome_pessoa,Quantidade de filmes
Kevin Hart,8


In [0]:
# 6. Qual a produtora de filmes teve o maior Lucro nos últimos 5 anos*?
df_dim_movies = spark.table(f"{gold_schema}.dim_movies")\
    .filter((F.col("status_filme") == "Lançado") & (F.col("data_lancamento") <= F.current_date()))\
    .select("sk_movie_id", "data_lancamento")
df_fact_movies = spark.table(f"{gold_schema}.fact_movies_performance")
df_dim_companies = spark.table(f"{gold_schema}.dim_companies")
df_bridge_movie_company = spark.table(f"{gold_schema}.bridge_movie_company")

# Para pegar 5 anos antes da data mais recente: retira dois anos da data e pega a maior
data_cinco_anos = df_dim_movies.agg(F.max(F.add_months(F.col("data_lancamento"), -60))).first()[0]

lucro_produtoras = (
    df_dim_movies
    # Mantém os filmes dos últimos 5 anos
    .filter(F.col("data_lancamento") >= data_cinco_anos)
    # Join obtém qual a produtora de cada filme e seu lucro
    .join(df_fact_movies, "sk_movie_id", "inner")
    .join(df_bridge_movie_company, "sk_movie_id", "inner")
    .join(df_dim_companies, "sk_company_id", "inner")
    # Agrupa por produtora e soma o lucro de cada
    .groupBy(["sk_company_id", "nome_produtora"])
    .agg(F.sum(F.col("lucro_brl")).alias("Lucro R$"), F.sum(F.col("lucro_usd")).alias("Lucro US$"))
    .select("nome_produtora", "Lucro R$", "Lucro US$")
)

# Seleciona a produtora de maior lucro
maior_lucro = lucro_produtoras.agg(F.max("Lucro R$")).first()[0]
produtora = lucro_produtoras.filter(F.col("Lucro R$") == maior_lucro)

display(produtora)

nome_produtora,Lucro R$,Lucro US$
Universal Pictures,2.8820664854260002E10,5772329679.00
